# OpenRAM Playground
[![Open In Colab](https://colab.research.google.com/assets/colab-badge.svg)](https://githubtocolab.com/sfmth/openram-playground/blob/main/OpenRAM.ipynb)

The OpenRAM Playground is a notebook that allows users to explore and experiment with OpenRAM, an open-source memory compiler. With this tool, users can generate and customize memory designs, view the final result, and learn more about the memory design process using OpenRAM. This project is authored by Farhad Modaresi.

# 1. Install OpenRAM and its dependancies


This will clone the OpenRAM repository (branch v1.2.8) into the "/tmp/OpenRAM" directory:

- The ```> /dev/null 2>&1``` part at the end of the command is a redirection to discard any output from the command, so the notebook remains clean and free of excessive output.

In [1]:
%cd /tmp
! git clone -b v1.2.8 https://github.com/VLSIDA/OpenRAM > /dev/null 2>&1

/tmp


Next, the working directory is changed to the installation path directory (/tmp/OpenRAM) by running the following command:

In [2]:
%cd /tmp/OpenRAM

/tmp/OpenRAM


Now, you need to run the "install_conda.sh" script to install the necessary tools using Anaconda. This script installs the following tools:

- Miniconda: a lightweight version of the Anaconda distribution, which provides an environment for managing Python packages.
- litex-hub: a collection of open-source tools for building digital hardware systems.
- iverilog: a simulator for Verilog HDL (hardware description language).
- VLSIDA-EDA: a suite of open-source tools for electronic design automation, including klayout (a layout editor), magic (a VLSI layout tool), netgen (a netlist comparison tool), ngspice (a circuit simulator), trilinos (a collection of libraries for linear and nonlinear solvers), and xyce (a parallel circuit simulator).

To run the script, use the following command:

In [ ]:
! ./install_conda.sh > /dev/null 2>&1

Once the script has finished running, you can install the Python requirements for OpenRAM by running the following command:

In [ ]:
! python -m pip install -r requirements.txt > /dev/null 2>&1

Finally, you need to set the environment variables used by the OpenRAM compiler and related tools to locate and use various files and libraries needed for the design and simulation of SRAM cells. To do this, run the following commands:

In [ ]:
%env OPENRAM_ROOT=/tmp/OpenRAM
%env OPENRAM_HOME="/tmp/OpenRAM/compiler"
%env OPENRAM_TECH="/tmp/OpenRAM/technology"
%env PYTHONPATH=$OPENRAM_HOME
%env PYTHONPATH="$OPENRAM_HOME:$OPENRAM_TECH/sky130:$OPENRAM_TECH/sky130/custom"

env: OPENRAM_ROOT=/tmp/OpenRAM
env: OPENRAM_HOME="/tmp/OpenRAM/compiler"
env: OPENRAM_TECH="/tmp/OpenRAM/technology"
env: PYTHONPATH=$OPENRAM_HOME
env: PYTHONPATH="$OPENRAM_HOME:$OPENRAM_TECH/sky130:$OPENRAM_TECH/sky130/custom"


These commands set the following environment variables:

- OPENRAM_ROOT: the root directory of the OpenRAM repository.
- OPENRAM_HOME: the directory containing the OpenRAM compiler.
- OPENRAM_TECH: the directory containing the OpenRAM technology files.
- PYTHONPATH: the Python path used by the OpenRAM compiler and related tools to locate various modules and packages.

# 2. Download PDK

This step downloads and sets up the SKY130 PDK, which includes SPICE models, GDS files, and libraries for tools such as Magic and Netgen. This step is required for designing and simulating SRAM cells using OpenRAM. The PDK includes various libraries and tools needed in the compilation process.

For this step we have to first activate the Miniconda environment using the following command:

```source miniconda/bin/activate```

We can also add the next command to install the PDK in the same line by using ```&&``` to chain commands.



In [ ]:
! source miniconda/bin/activate && make pdk > /dev/null 2>&1

# 3. Install SRAM Build Space

This step downloads and sets up the SKY130 SRAM build space, which contains the necessary components for OpenRAM to compile SRAM macros. The build space includes technology-specific configuration files and models, as well as scripts for building and testing SRAM macros.

The build space is cloned from its [github repository](https://github.com/vlsida/sky130_fd_bd_sram.git) and then the required files are installed to the "/tmp/OpenRAM/technology/sky130" directory.

In [ ]:
! make install > /dev/null 2>&1

# 4. Install GDS viewers

Firstly the working directory has to be changed as we are installing the tools in the /tmp directory.

In [ ]:
%cd /tmp

/tmp


The below code installs the Python package called gdstk. gdstk is a Python package for working with GDSII (Graphic Data System II) files, which are typically used in microelectronics for exchanging layout data between different CAD (Computer-Aided Design) tools.

In this notebook this package is used to convert GDSII files that are generated by OpenRAM to SVG files that are easier to view.

In [ ]:
! pip install gdstk > /dev/null 2>&1

The below code installs the Python package called cairosvg. cairosvg is a Python package that can be used to convert SVG (Scalable Vector Graphics) files to PNG (Portable Network Graphics) format.

Vector images (SVG) are not widely supported across different softwares, it is easier to use a raster image format such as PNG to view and modify images. Hence cairosvg is used to convert the output of gdstk to PNG which is a raster image format.

In [ ]:
!pip install  cairosvg  > /dev/null 2>&1

The below code defines a Python function ```gds2d_view``` that takes a GDSII file as input, converts it to an SVG file using the gdstk package, and then converts the SVG file to a PNG file using the cairosvg package. The function returns an IPython Image object that can be displayed in a Jupyter notebook.

This function can also control the output resolution by modifying the ```scale``` parameter.

In [ ]:
import gdstk
import cairosvg
from IPython.display import Image
def gds2d_view(gds_file, scale=10):
  svg = gds_file.split(".")[0] + ".svg"
  png = gds_file.split(".")[0] + ".png"
  library = gdstk.read_gds(gds_file)
  top_cells = library.top_level()
  top_cells[0].write_svg(svg)
  cairosvg.svg2png(url=svg, write_to=png, scale=scale)
  return Image(png)

Install GDS to glTF conversion script: This section installs a Python3 script made by Maximo called "GDS2glTF" which is a converter for GDSII files to glTF (GL Transmission Format) files. GDSII is a file format used in the design of integrated circuits and glTF is a file format used for 3D graphics. This script allows users to convert GDSII files of their SRAM designs into glTF files that can be used for 3D rendering.

In [ ]:
! git clone https://github.com/mbalestrini/GDS2glTF.git > /dev/null 2>&1
! python -m pip install -r GDS2glTF/requirements.txt > /dev/null 2>&1

Install glTF HTML viewer: This section installs an HTML viewer for glTF files made by Johan Euphrosine (Proppy) that allows users to view their 3D renders of their SRAM designs. This HTML viewer is added as a Jinja2 template that is loaded in the next line of code.
jinja2 is a Python package that is used to load the HTML template for the viewer. To do this we have to import the Jinja2 templating engine and set the "gds_viewer" variable to point to the "viewer.html" file in the cloned "gds_viewer" directory. This file is used to render the 3D view of the SRAM macro.

In [ ]:
!git clone https://github.com/proppy/gds_viewer.git > /dev/null 2>&1
import jinja2
gds_viewer = jinja2.Environment(loader=jinja2.FileSystemLoader('gds_viewer')).get_template('viewer.html')

Overall, this notebook allows users to create 3D renders of their SRAM designs by converting their GDSII files to glTF files and then viewing them using the glTF HTML viewer.

Finally the working directore has to be changed back to the OpenRAM's root directory:

In [ ]:
%cd /tmp/OpenRAM

/tmp/OpenRAM


# 5. SRAM Cells

## Single Port SRAM Cell

This code generates an image of a single port SRAM cell from a pre-defined GDS file. It starts by defining the path to the GDS file, which is stored in the gds variable.

In [ ]:
gds = "technology/sky130/gds_lib/sky130_fd_bd_sram__sram_sp_cell_opt1.gds"

Then, it uses a Python script called gds2gltf.py to convert the GDS file into a glTF file format. The converted glTF file is saved in the same directory as the GDS file, with the extension .gltf.

In [ ]:
! python3 /tmp/GDS2glTF/gds2gltf.py $gds > /dev/null 2>&1

The IPython.display.clear_output function is used to clear the output area before displaying the HTML output, so that previous outputs are not displayed along with the current one.

In [ ]:
import IPython.display
IPython.display.clear_output(wait=True)

Next, the code uses the gds_viewer template defined earlier to render the glTF data and generate an HTML output that displays the 3D view of the single port SRAM cell.

In [ ]:
with open(f'{gds}.gltf') as f:
  gltf_data=f.read()
  output = gds_viewer.render(gltf_data=gltf_data)

 The output is then displayed in the Jupyter notebook using the IPython.display.HTML function.

In [ ]:
IPython.display.HTML(output)

## Dual Port SRAM Cell

The code here works just like the one described above, however the input gds variable points to a different file.

In [ ]:
gds = "technology/sky130/gds_lib/sky130_fd_bd_sram__openram_dp_cell.gds"
! python3 /tmp/GDS2glTF/gds2gltf.py $gds > /dev/null 2>&1
import IPython.display
IPython.display.clear_output(wait=True)
with open(f'{gds}.gltf') as f:
  gltf_data=f.read()
  output = gds_viewer.render(gltf_data=gltf_data)
IPython.display.HTML(output)

# 7. Macro specifications:
Defines the SRAM macro specifications.

This section defines the specifications of the SRAM macro that will be created. The code uses the magic command %%writefile to write a Python script that will contain the specifications. The specifications include:

- word_size: The size of a single memory word in bits.
- num_words: The total number of words in the SRAM.
- human_byte_size: The total size of the SRAM in kilobytes, rounded to the nearest whole number.
- write_size: The number of bits that can be written at a time.
- num_rw_ports, num_r_ports, num_w_ports: The number of read/write, read-only, and write-only ports, respectively. In this case, there is 1 read/write port and 1 read-only port.
- ports_human: A string representation of the port configuration, which is set to "1rw1r" for 1 read/write and 1 read-only port.

The last line of the code executes another Python script (sky130_sram_common.py) which contains common functions used to create the SRAM macro.

In [ ]:
%%writefile macros/sram_configs/myconfig.py

"""
Dual port (1 read/write + 1 read only) 1 kbytes SRAM with byte write.
"""
word_size = 8

num_words = 16

human_byte_size = "{:.0f}kbytes".format((word_size * num_words)/1024/8)

# Allow byte writes
write_size = 2 # Bits

# Dual port
num_rw_ports = 1
num_r_ports = 1
num_w_ports = 0
ports_human = '1rw1r'

import os
exec(open(os.path.join(os.path.dirname(__file__), 'sky130_sram_common.py')).read())

Writing macros/sram_configs/myconfig.py


You can modify the specs using the following form fields as well.
- Please note that the following variables overwrite the values in the previous file

In [ ]:

config_file = "macros/sram_configs/myconfig.py"


#@markdown ---
#@markdown ### Number of bits for each memory word:
word_size = 8 #@param {type:"raw"}

#@markdown ---
#@markdown ### Total number of memory words:
num_words = 16 #@param {type:"raw"}

#@markdown ---
#@markdown ### Lowest number of writable bits in one write cylce:
write_size = 2 #@param {type:"raw"}

#@markdown ---
#@markdown ### Number of Read/Write ports:
num_rw_ports = 1 #@param {type:"raw"}

#@markdown ---
#@markdown ### Number of Read only ports:
num_r_ports = 1 #@param {type:"raw"}

#@markdown ---
#@markdown ### Number of Write only ports:
num_w_ports = 0 #@param {type:"raw"}

#@markdown ---



! sed -i "s/^word_size.*$/word_size = $word_size/" $config_file
! sed -i "s/^num_words.*$/num_words = $num_words/" $config_file
! sed -i "s/^write_size.*$/write_size = $write_size/" $config_file
! sed -i "s/^num_rw_ports.*$/num_rw_ports = $num_rw_ports/" $config_file
! sed -i "s/^num_r_ports.*$/num_r_ports = $num_r_ports/" $config_file
! sed -i "s/^num_w_ports.*$/num_w_ports = $num_w_ports/" $config_file
! sed -i "s/^FIXME.*$//" $config_file


# 8. Compile the SRAM macro for SKY130 using the above specs:


This line of code changes the directory to macros/ where a Make file is loacted and runs the make command with the argument myconfig.ok. The make command is a tool for managing source code compilation, and the argument myconfig.ok specifies the target to be built.

This target will build an SRAM macro by calling the sram_compiler.py script according to the specifications defined in the myconfig.py file created in the previous step.

In [ ]:
! cd macros/ && make myconfig.ok > /dev/null 2>&1

# 9. 2D GDS view:

The following code generates a 2D GDS view of the SRAM macro that was just compiled in the previous step.

- config_stem is a variable that holds the name of the SRAM configuration.
- gds is a variable that holds the path to the GDS file of the SRAM macro based on the config_stem.
- gds2d_view() is a function that was defined earlier in the notebook to generate a 2D view of a GDS file.

So, this code calls the gds2d_view() function on the gds file to generate a 2D view of the SRAM macro.

In [ ]:
config_stem= "myconfig"
gds = "macros/" + config_stem + "/" + config_stem + ".gds"

gds2d_view(gds)

# 10. 3D GDS View

This section is similar to section 5, where it generates a 3D GDS view of the SRAM cell. The code first sets the configuration stem to "myconfig", which is the same name used when compiling the SRAM macro in section 8. Then it sets the gds variable to the path of the GDS file of the compiled macro.

In [ ]:
config_stem= "myconfig"
gds = "macros/" + config_stem + "/" + config_stem + ".gds"

The code then uses the GDS2glTF tool again to convert the GDS file to a glTF file, which can be used to generate a 3D view of the SRAM macro. After the conversion, the code reads the glTF file and generates the 3D view using the same glTF viewer used in section 5.

In [ ]:
! python3 /tmp/GDS2glTF/gds2gltf.py $gds > /dev/null 2>&1
import IPython.display
IPython.display.clear_output(wait=True)
with open(f'{gds}.gltf') as f:
  gltf_data=f.read()
  output = gds_viewer.render(gltf_data=gltf_data)

Finally, the code displays the generated 3D view of the SRAM macro in the notebook using the IPython.display.HTML method.

In [ ]:
IPython.display.HTML(output)